# Human lymph node: domains and hierarchical communication

Paired RNA and standardized ADT cover 3,484 observations. The tutorial relates spatial domains to immune lineages and examines the saved four-level LR hierarchy.

Training is commented out by default. **Run All** uses saved CellSTIC results and recomputes the analyses below. Figures and tables are saved alongside the existing model results under `DATA / "cellstic"`. Run All does not train or modify the saved model.

## 1. Set up the dataset

Start Jupyter from this repository. Use the environment in `environment.yml` and supply the assembled inputs and saved results at the paths below.

In [1]:
from pathlib import Path
import sys
import json
import anndata as ad
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt
from IPython.display import display, SVG, Markdown

ROOT = next(p for p in [Path.cwd(), *Path.cwd().parents] if (p / "pipeline/cellstic.py").is_file())
if str(ROOT) not in sys.path:
    sys.path.insert(0, str(ROOT))
from pipeline.analysis import Analysis
from utils.analysis.result_io import load_result, lr_matrices, channel_keys
from utils.analysis import dataset_analysis as da
%matplotlib inline
plt.style.use("default")
plt.rcParams.update({"font.size": 10, "figure.dpi": 110})

<conda-env>/lib/python3.8/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


In [2]:
DATA = ROOT / "paper/data/human_lymph_node"
RESULT_PATH = DATA / "cellstic/out/out.h5ad"
OUTPUT = DATA / "cellstic"
OUTPUT.mkdir(parents=True, exist_ok=True)

## 2. Train CellSTIC (optional)

Uncomment both cells to fit the assembled inputs. The pipeline performs normalization, feature extraction, graph construction and training. If explicitly enabled, training writes to the same output location used below and replaces that saved fit. The lymph-node preset uses an LLM hierarchy and requires the configured LLM and embedding resources. The saved result retains its original hierarchy; a new fit may produce different groups.

In [3]:
# from model.train import get_cellstic_config
# from pipeline.cellstic import run_cellstic
# names = ['rna', 'adt']
# inputs = [ad.read_h5ad(DATA / "h5ad" / f"{name}.h5ad") for name in names]
# config = get_cellstic_config('human_lymph_node')

In [4]:
# from utils.tools import CellChatDBLoader
# lr_map = {name: list(values) for name, values in inputs[0].uns["ligand_receptor_map"].items()}
# trained = run_cellstic(inputs, config, modality_types=["rna", "adt_standardized"],
#                       ligand_receptor_map=lr_map,
#                       cell_chat_db=CellChatDBLoader().get_ligand_receptor_map("human"),
#                       output_path=OUTPUT)
# RESULT_PATH = OUTPUT / "out/out.h5ad"

## 3. Load the saved result

Load the spatial metadata, embedding and predicted graphs. Expression and auxiliary calibration arrays stay on disk.

In [5]:
result = load_result(RESULT_PATH)
display(pd.DataFrame({"observations": [result.n_obs],
                      "domains": [result.obs["cluster"].nunique()],
                      "LR channels": [len(channel_keys(result.obsp, result.uns["cellstic"]))]}))

,observations,domains,LR channels
0,3484,8,26


## 4. Inspect spatial domains

Colors show the saved domain assignments. The spatial visualizer uses the measured coordinates.

In [6]:
from utils.metrics.spatial_viz import SpatialVisualizer
from utils.analysis.figure_export import show_image_row
spatial = ad.AnnData(obs=result.obs.copy(), obsm={"spatial": result.obsm["spatial"]})
spatial.obs["cluster"] = pd.Categorical(result.obs['cluster'].astype(str))
(OUTPUT / "domain").mkdir(parents=True, exist_ok=True)
SpatialVisualizer.generate_spatial_domain_visualization(
    spatial, save_path=OUTPUT / "domain/spatial_domain.svg", size_multiplier=0.85)
show_image_row([OUTPUT / "domain/spatial_domain.svg"])

<conda-env>/lib/python3.8/site-packages/anndata/_core/anndata.py:121: ImplicitModificationWarning: Transforming to str index.
  warnings.warn("Transforming to str index.", ImplicitModificationWarning)


Visualizing 3484 points with 8 domains in grid style
  Calculated min nearest neighbor distance: 162.0123
  Square size (base * 0.85): 165.2526
  Direct visualization: 3484 points, each point gets its own square


Spatial domain visualization (grid style) saved to ./paper/data/human_lymph_node/cellstic/domain/spatial_domain.svg


## 5. Relate domains to immune lineages

Count the annotated lineages in each learned domain. The labels describe cell identity rather than directly measuring signaling.

In [7]:
counts = pd.crosstab(result.obs["cluster"], result.obs["cell_type"])
display(counts)
counts.to_csv(OUTPUT / "domain/domain_celltypes.csv")

cell_type,B lineage,Cytotoxic / innate-like T,Erythroid / MK,Helper / Regulatory T,Myeloid,NK / ILC,Others,Plasma lineage,Stromal / non-immune
cluster,,,,,,,,,
0,128,54,7,183,54,9,2,307,25
1,105,36,6,235,37,4,2,238,12
2,53,40,3,93,35,9,4,311,31
3,46,39,1,90,44,10,6,244,30
4,55,14,1,82,22,34,4,155,30
5,26,21,1,68,20,4,0,146,14
6,22,9,1,42,11,0,0,61,7
7,21,10,2,18,7,1,0,39,3


## 6. Summarize the three level-2 communication groups

These tables sum stored ancestor-channel weights by directed domain pair. Archived ancestor channels may have been predicted separately; the tutorial does not assume they equal leaf sums.

In [8]:
keys = channel_keys(result.obsp, result.uns["cellstic"], leaf_only=False)
level2 = {name: result.obsp[key] for (level, name), key in keys.items() if level == 2}
(OUTPUT / "ccc").mkdir(parents=True, exist_ok=True)
for i, (name, matrix) in enumerate(level2.items()):
    table = da.group_communication(result, matrix, "cluster")
    display(Markdown("**" + name + "**"))
    display(table.round(3))
    table.to_csv(OUTPUT / "ccc" / f"level2_{i}_domain_strength.csv")

**Adhesion and Cell-Cell Communication Mediators**

receiver,0,1,2,3,4,5,6,7
sender,,,,,,,,
0,205.872,149.268,76.220,50.546,17.969,22.508,17.863,10.789
1,165.637,318.969,83.798,50.822,22.005,26.844,39.196,18.827
2,62.685,60.644,114.972,34.676,14.161,19.165,12.359,10.366
3,59.206,60.210,58.116,91.617,8.155,21.629,15.278,10.517
4,43.636,49.577,17.682,9.807,55.420,4.156,3.982,3.721
5,35.064,28.542,30.098,23.091,5.251,30.288,10.529,5.775
6,23.825,45.599,19.336,14.754,2.402,9.560,35.393,6.112
7,18.448,27.777,13.547,11.331,1.287,7.573,10.606,15.060


**Chemokine Signaling Axis**

receiver,0,1,2,3,4,5,6,7
sender,,,,,,,,
0,386.762,258.338,65.969,29.002,13.686,38.499,34.942,7.319
1,255.348,519.411,59.857,35.946,15.217,43.292,51.124,6.145
2,68.187,70.133,80.300,18.246,4.838,17.190,14.388,3.878
3,43.963,46.188,26.608,30.638,1.998,14.904,10.555,2.721
4,45.491,54.968,15.255,9.986,32.105,3.181,2.896,1.126
5,48.465,63.275,19.114,10.343,0.852,34.224,12.283,2.436
6,37.900,55.360,14.600,7.546,1.093,11.213,34.144,2.447
7,19.675,19.336,9.841,7.565,0.640,6.177,5.937,6.099


**Immunomodulatory Cytokine and Co-stimulatory Pathways**

receiver,0,1,2,3,4,5,6,7
sender,,,,,,,,
0,354.514,199.740,64.055,52.207,49.502,35.038,30.525,20.171
1,208.277,377.577,67.610,42.868,39.289,23.738,38.904,19.348
2,74.749,66.224,87.098,33.637,9.402,22.096,19.293,12.121
3,42.027,36.831,22.705,55.850,7.482,16.912,8.563,6.525
4,24.965,28.087,3.948,3.827,42.492,1.489,1.305,0.298
5,28.301,34.588,14.731,18.274,2.861,37.751,9.364,4.021
6,23.856,29.519,12.330,9.800,2.703,8.584,31.025,4.599
7,23.398,24.521,13.597,14.963,1.770,6.657,12.500,19.902


## 7. Map level-2 spatial communication strength

Each map shows one of the three saved L2 communication groups. At each observation, sum outgoing and incoming weights after excluding self connections, then plot `log1p(strength)`. The three maps use a shared color scale and the measured tissue coordinates. All positive stored L2 edges contribute; these ancestor scores are read directly from the saved result.

In [9]:
analysis = Analysis.from_result(result, output_path=OUTPUT)
l2_titles = {
    "Adhesion and Cell-Cell Communication Mediators": "Adhesion & cell-contact\nmediators",
    "Chemokine Signaling Axis": "Chemokine signaling\naxis",
    "Immunomodulatory Cytokine and Co-stimulatory Pathways": "Immunomodulatory cytokine\n& co-stimulation",
}
l2_figure = analysis.plot_hierarchy_spatial_strength(level=2, channel_titles=l2_titles)
show_image_row([l2_figure])

## 8. Explore B-lineage and helper-T communication hierarchies

Select B and helper/regulatory T lineages and draw their four directed pairings. The existing hierarchy visualizer aggregates leaf strengths through the stored hierarchy; strip widths describe relative strength within each pairing.

In [10]:
lineages = ["B lineage", "Helper / Regulatory T"]
subset = result[result.obs["cell_type"].isin(lineages)].copy()
hierarchy = Analysis.from_result(subset, output_path=OUTPUT)
hierarchy.plot_hierarchy(group_by="cell_type", group_key="cell_type", threshold=0.0,
                         min_count_threshold=1, show_title=True)
names = ["B_lineage", "Helper___Regulatory_T"]
figures = [OUTPUT / "alluvial/cell_type_pairs" / f"alluvial_cell_type_{a}_to_{b}_icicle.svg"
           for a in names for b in names]
show_image_row(figures)

Sender/receiver stacked bar saved to ./paper/data/human_lymph_node/cellstic/alluvial/cell_type_bar/lr_pair_stacked_bar_level_2.svg


Sender/receiver stacked bar saved to ./paper/data/human_lymph_node/cellstic/alluvial/cell_type_bar/lr_pair_stacked_bar_level_3.svg


Sender/receiver stacked bar saved to ./paper/data/human_lymph_node/cellstic/alluvial/cell_type_bar/lr_pair_stacked_bar_level_4.svg


## 9. Compare cell-type communication hierarchies

Match `paper/analysis/human_lymph_node/plot_panel_e.py`: fix Helper / Regulatory T as the sender and select four receivers with at least 200 observations, excluding Others, by their distinct LR compositions. Selection maximizes the minimum pairwise Jensen–Shannon distance, then the mean distance.

For the saved result, the receivers are B lineage (top), Cytotoxic / innate-like T (right), Helper / Regulatory T (bottom), and Myeloid (left). The plot uses the full saved result loaded above; widths show relative LR contributions within each pair.

In [12]:
square_figure = analysis.plot_cell_type_hierarchy_square(
    sender="Helper / Regulatory T",
    min_receiver_cells=200,
    threshold=0.0,
    min_count_threshold=1,
    size_mm=84.0,
    dpi=600,
)
show_image_row([square_figure])

## 10. Map selected ligand–receptor networks

Two chemokine channels illustrate spatial differences within the lymph node. The existing visualizer collapses each directed pair to an undirected display edge and retains at most three incident edges per observation. The preceding L2 summaries use the full stored directed graphs.

In [11]:
from utils.visualization import LigandReceptorSpatialVisualizer
PAIRS = ['CXCL13:CXCR5', 'CCL19:CCR7']
matrices = lr_matrices(result)
selected = {pair: i for i, pair in enumerate(PAIRS)}
LigandReceptorSpatialVisualizer().plot_ligand_receptor_spatial_distribution(
    adata=result, edge_type_map=selected, pos_edge_probs=[matrices[p] for p in PAIRS],
    lr_filter=PAIRS, threshold=0.0, save_path=OUTPUT / "ccc")
figures = [OUTPUT / "ccc" / ("lr_spatial_" + pair.replace(":", "_") + ".svg") for pair in PAIRS]
show_image_row(figures, labels=PAIRS)

Found 2 valid ligand-receptor pairs
